In [ ]:
import numpy as np
import matplotlib.pyplot as plt
from matplotlib.animation import FuncAnimation
from scipy.integrate import quad
from IPython.display import HTML

L = 1.0
c = 1.0

def u0(x):
    return np.where((x >= 0.4) & (x <= 0.6), np.sin(5 * np.pi * x), 0)

def compute_coefficients(phi, N_terms=50):
    A = np.zeros(N_terms)
    for k in range(N_terms):
        lam = (2 * k + 1) * np.pi / (2 * L)
        integrand = lambda x_val: phi(np.array([x_val]))[0] * np.sin(lam * x_val)
        A[k], _ = quad(integrand, 0, L)
        A[k] *= 2 / L
    return A

def u_analytical(x, t, phi_coef, N_terms=50):
    u = np.zeros_like(x)
    for k in range(N_terms):
        lam = (2 * k + 1) * np.pi / (2 * L)
        u += phi_coef[k] * np.sin(lam * x) * np.cos(c * lam * t)
    return u

phi_coef = compute_coefficients(u0, 50)

In [ ]:
#Явная схема крест 
def solve_explicit(x, t, u0_func, u_left=0):
    Nx, Nt = len(x), len(t)
    h = x[1] - x[0]
    tau = t[1] - t[0]
    r = (c * tau / h) ** 2
    assert r <= 1.0, "Не устойчиво"
    u = np.zeros((Nt, Nx))
    u[0, :] = u0_func(x)
    N = Nx - 1
    # Первый шаг по времени 
    for n in range(1, N):
        u[1, n] = u[0, n] + 0.5 * r * (u[0, n+1] - 2*u[0, n] + u[0, n-1])
    u[1, 0] = u_left
    u[1, N] = u[1, N-1]
    for m in range(1, Nt - 1):
        u[m+1, 0] = u_left
        for n in range(1, N):
            u[m+1, n] = 2*u[m, n] - u[m-1, n] + r * (u[m, n+1] - 2*u[m, n] + u[m, n-1])
        u[m+1, N] = u[m+1, N-1]
    return u

In [ ]:
def solve_tridiag(a, b, c_coef, d):
    n = len(d)
    for i in range(1, n):
        w = a[i] / b[i-1]
        b[i] -= w * c_coef[i-1]
        d[i] -= w * d[i-1]
    x_sol = np.zeros(n)
    x_sol[-1] = d[-1] / b[-1]
    for i in range(n-2, -1, -1):
        x_sol[i] = (d[i] - c_coef[i] * x_sol[i+1]) / b[i]
    return x_sol

#Неявная Т-схема и прогонка
def solve_implicit(x, t, u0_func, u_left=0):
    Nx, Nt = len(x), len(t)
    h = x[1] - x[0]
    tau = t[1] - t[0]
    r = (c * tau / h) ** 2
    u = np.zeros((Nx, Nt))
    u[:, 0] = u0_func(x)
    u[:, 1] = u0_func(x)          
    for j in range(1, Nt - 1):
        a = np.full(Nx, -r)
        b = np.full(Nx, 1 + 2*r)
        c_coef = np.full(Nx, -r)
        d = np.zeros(Nx)
        for i in range(1, Nx - 1):
            d[i] = 2*u[i,j] - u[i,j-1]
        # Левый конец: u_0 = 0
        d[0], a[0], b[0], c_coef[0] = u_left, 0, 1, 0
        # Правый конец (свободный): -
        d[-1] = 2*u[-1,j] - u[-1,j-1]
        a[-1], b[-1], c_coef[-1] = -2*r, 1 + 2*r, 0
        u[:, j+1] = solve_tridiag(a, b, c_coef, d)
    return u

In [62]:
T = 10.0
dx = 0.02
dt = 0.01
Nx = int(L / dx) + 1
Nt = int(T / dt) + 1
x = np.linspace(0, L, Nx)
t = np.linspace(0, T, Nt)

u_exp = solve_explicit(x, t, u0)
u_an = np.zeros((Nx, Nt))
for j in range(Nt):
    u_an[:, j] = u_analytical(x, t[j], phi_coef)
u_imp = solve_implicit(x, t, u0)


In [63]:
step = 2
n_frames = (Nt - 1) // step + 1
fig, ax = plt.subplots(figsize=(10, 5))
line_exp, = ax.plot(x, u_exp[0, :], 'b-', lw=1.5, label='Явная')
line_an,  = ax.plot(x, u_an[:, 0], 'g-', lw=2, label='Аналитическое')
line_imp, = ax.plot(x, u_imp[:, 0], 'r--', lw=1.5, label='Неявная')
ax.set_xlim(0, L)
ax.set_ylim(-1.15, 1.15)
ax.set_xlabel('$x$')
ax.set_ylabel('$u(x,t)$')
ax.legend()
ax.grid(True, alpha=0.3)

def animate(k):
    j = min(k * step, Nt - 1)
    line_exp.set_ydata(u_exp[j, :])
    line_an.set_ydata(u_an[:, j])
    line_imp.set_ydata(u_imp[:, j])
    ax.set_title(f'$t = {t[j]:.2f}$')
    return line_exp, line_an, line_imp

anim = FuncAnimation(fig, animate, frames=n_frames, interval=80, blit=True, repeat=True)
plt.tight_layout()
plt.close(fig)
HTML(anim.to_jshtml())

Animation size has reached 21006587 bytes, exceeding the limit of 20971520.0. If you're sure you want a larger animation embedded, set the animation.embed_limit rc parameter to a larger value (in MB). This and further frames will be dropped.
